# Insert formatted MJP data into the VMM/ELI RDF model

Run this notebook after `format_vmm.ipynb`. It reads the JSONL handoff produced by that
notebook, validates every delivery, generates VMM/ELI triples, and inserts them into the
public graph in bounded batches.

The hierarchy keeps strategic goals, policy goals, action plans, and actions as separate
Work/Expression resources. Records without a parent are linked directly to their delivery
as `dct:hasPart` resources.

## 1. Configuration

The default paths work when the notebook is run from `vmm-dev` or any child directory. Set
`DRY_RUN = True` to validate and generate batches without sending SPARQL updates.

In [5]:
from __future__ import annotations

import json
import math
import uuid
from pathlib import Path
from typing import Any, Iterator

import requests


def find_project_root() -> Path:
    candidates = [Path.cwd(), Path.cwd() / "vmm-dev"]
    candidates.extend(Path.cwd().parents)
    for candidate in candidates:
        candidate = candidate.resolve()
        if (candidate / "vmm-data").is_dir() and (candidate / "data" / "insert").is_dir():
            return candidate
    raise FileNotFoundError(
        "Could not find the vmm-dev project root. Run the notebook from vmm-dev "
        "or one of its child directories."
    )


PROJECT_ROOT = find_project_root()
SPARQL_URL = "http://localhost:8890/sparql"
PUBLIC_GRAPH = "http://mu.semte.ch/graphs/public"
MJP_SOURCE_FILE = PROJECT_ROOT / "data" / "insert" / "data" / "vap_mjp_structured_2.jsonl"
DRY_RUN = True
MAX_DELIVERIES: int | None = None
MAX_TRIPLES_PER_UPDATE = 4_000
VMM_BASE = "http://lblod.data.gift/vocabularies/vmm/"

PREFIXES = """
PREFIX dct:    <http://purl.org/dc/terms/>
PREFIX eli:    <http://data.europa.eu/eli/ontology#>
PREFIX epvoc:  <https://data.europarl.europa.eu/def/epvoc#>
PREFIX mu:     <http://mu.semte.ch/vocabularies/core/>
PREFIX schema: <http://schema.org/>
PREFIX vmm:    <http://lblod.data.gift/vocabularies/vmm/>
PREFIX xsd:    <http://www.w3.org/2001/XMLSchema#>
""".strip()

print(f"Project root: {PROJECT_ROOT}")
print(f"JSONL source: {MJP_SOURCE_FILE}")
print(f"SPARQL URL:  {SPARQL_URL}")
print(f"Dry run:     {DRY_RUN}")

Project root: D:\OneDrive - Sirus NV\ABB\app-vmm\vmm-dev
JSONL source: D:\OneDrive - Sirus NV\ABB\app-vmm\vmm-dev\data\insert\data\vap_mjp_structured_2.jsonl
SPARQL URL:  http://localhost:8890/sparql
Dry run:     True


## 2. SPARQL and input helpers

In [6]:
def sparql_update(query: str) -> requests.Response:
    response = requests.post(
        SPARQL_URL,
        data={"query": query},
        timeout=120,
    )
    response.raise_for_status()
    return response


def is_blank(value: Any) -> bool:
    if value is None:
        return True
    if isinstance(value, float) and math.isnan(value):
        return True
    return str(value).strip() == ""


def text_value(value: Any) -> str | None:
    if is_blank(value):
        return None
    return str(value).strip()


def first_value(data: dict[str, Any], *keys: str) -> Any:
    for key in keys:
        if key in data:
            return data[key]
    return None


def sparql_string(value: Any) -> str:
    text = text_value(value)
    if text is None:
        raise ValueError("Cannot serialize a blank value as a required literal.")
    return json.dumps(text, ensure_ascii=False)


def sparql_boolean(value: Any) -> str | None:
    if is_blank(value):
        return None
    if isinstance(value, bool):
        return "true" if value else "false"
    if isinstance(value, (int, float)) and value in (0, 1):
        return "true" if int(value) == 1 else "false"
    normalized = str(value).strip().lower()
    if normalized in {"true", "1", "yes", "ja"}:
        return "true"
    if normalized in {"false", "0", "no", "nee"}:
        return "false"
    raise ValueError(f"Unsupported boolean value: {value!r}")


def uri(kind: str, source_id: Any) -> str:
    identifier = text_value(source_id)
    if identifier is None:
        raise ValueError(f"Missing identifier for {kind}.")
    return f"{VMM_BASE}{kind}/{identifier}"


def expression_uri(kind: str, source_id: Any) -> str:
    return f"{uri(kind, source_id)}/expression"


def resource_uuid(resource_uri: str) -> str:
    return str(uuid.uuid5(uuid.NAMESPACE_URL, resource_uri))


def iter_jsonl(path: Path) -> Iterator[tuple[int, dict[str, Any]]]:
    with path.open("r", encoding="utf-8-sig") as handle:
        for line_number, raw_line in enumerate(handle, start=1):
            if not raw_line.strip():
                continue
            try:
                record = json.loads(raw_line)
            except json.JSONDecodeError as exc:
                raise ValueError(f"Invalid JSON on line {line_number}: {exc.msg}") from exc
            if not isinstance(record, dict):
                raise ValueError(
                    f"Line {line_number} must contain a JSON object, not {type(record).__name__}."
                )
            yield line_number, record


def require_id(entity: dict[str, Any], *, kind: str, context: str) -> str:
    identifier = text_value(entity.get("id"))
    if identifier is None:
        raise ValueError(f"{context}: {kind} is missing its `id`.")
    return identifier

## 3. Read and validate the formatter output

In [7]:
def validate_delivery(delivery: dict[str, Any], *, line_number: int) -> dict[str, int]:
    require_id(delivery, kind="aanlevering", context=f"Line {line_number}")
    counts = {
        "aanleveringen": 1,
        "strategische_doelstellingen": 0,
        "beleidsdoelstellingen": 0,
        "actieplannen": 0,
        "acties": 0,
    }
    count_keys = {
        "strategische_doelstelling": "strategische_doelstellingen",
        "beleidsdoelstelling": "beleidsdoelstellingen",
        "actieplan": "actieplannen",
        "actie": "acties",
    }
    seen = {kind: set() for kind in count_keys}

    def validate_entity(entity: Any, kind: str, context: str) -> str:
        if not isinstance(entity, dict):
            raise ValueError(f"{context}: expected an object.")
        identifier = require_id(entity, kind=kind, context=context)
        if identifier in seen[kind]:
            raise ValueError(f"Line {line_number}: duplicate {kind} ID {identifier}.")
        seen[kind].add(identifier)
        counts[count_keys[kind]] += 1
        return identifier

    def validate_actions(actions: Any, context: str) -> None:
        if not isinstance(actions, list):
            raise ValueError(f"{context}: `acties` must be an array.")
        for index, action in enumerate(actions):
            validate_entity(action, "actie", f"{context}, actie {index}")

    def validate_actionplans(actionplans: Any, context: str) -> None:
        if not isinstance(actionplans, list):
            raise ValueError(f"{context}: `actieplannen` must be an array.")
        for index, actionplan in enumerate(actionplans):
            actionplan_id = validate_entity(actionplan, "actieplan", f"{context}, actieplan {index}")
            validate_actions(actionplan.get("acties", []) or [], f"{context}, actieplan {actionplan_id}")

    strategic_goals = delivery.get("strategische_doelstellingen", []) or []
    if not isinstance(strategic_goals, list):
        raise ValueError(f"Line {line_number}: `strategische_doelstellingen` must be an array.")
    for index, strategic in enumerate(strategic_goals):
        strategic_id = validate_entity(strategic, "strategische_doelstelling", f"Line {line_number}, strategische doelstelling {index}")
        policy_goals = strategic.get("beleidsdoelstellingen", []) or []
        if not isinstance(policy_goals, list):
            raise ValueError(f"Line {line_number}, strategische doelstelling {strategic_id}: `beleidsdoelstellingen` must be an array.")
        for policy_index, policy in enumerate(policy_goals):
            policy_id = validate_entity(policy, "beleidsdoelstelling", f"Line {line_number}, beleidsdoelstelling {policy_index}")
            validate_actionplans(policy.get("actieplannen", []) or [], f"Line {line_number}, beleidsdoelstelling {policy_id}")

    validate_actionplans(delivery.get("actieplannen", []) or [], f"Line {line_number}, direct actieplannen")
    validate_actions(delivery.get("acties", []) or [], f"Line {line_number}, direct acties")
    return counts


if not MJP_SOURCE_FILE.is_file():
    raise FileNotFoundError(f"JSONL source file not found: {MJP_SOURCE_FILE}")

deliveries: list[tuple[int, dict[str, Any]]] = []
total_counts = {
    "aanleveringen": 0,
    "strategische_doelstellingen": 0,
    "beleidsdoelstellingen": 0,
    "actieplannen": 0,
    "acties": 0,
}
seen_delivery_ids: set[str] = set()

for line_number, delivery in iter_jsonl(MJP_SOURCE_FILE):
    delivery_id = require_id(delivery, kind="aanlevering", context=f"Line {line_number}")
    if delivery_id in seen_delivery_ids:
        raise ValueError(f"Duplicate aanlevering ID {delivery_id} on line {line_number}.")
    counts = validate_delivery(delivery, line_number=line_number)
    seen_delivery_ids.add(delivery_id)
    deliveries.append((line_number, delivery))
    for key, value in counts.items():
        total_counts[key] += value
    if MAX_DELIVERIES is not None and len(deliveries) >= MAX_DELIVERIES:
        break

print(f"Validated {len(deliveries)} deliveries from {MJP_SOURCE_FILE.name}.")
for key, value in total_counts.items():
    print(f"  {key}: {value}")

Validated 969 deliveries from vap_mjp_structured_2.jsonl.
  aanleveringen: 969
  strategische_doelstellingen: 1483
  beleidsdoelstellingen: 7432
  actieplannen: 29905
  acties: 118680


## 4. JSON-to-RDF transformation

Each policy entity receives one deterministic Work URI and one Expression URI. Direct
root-level action plans and actions are linked to the delivery with `dct:hasPart`.

In [10]:
def add_work(
    triples: list[str],
    entity: dict[str, Any],
    *,
    kind: str,
    label: str,
    rdf_type: str,
    complex_work: bool,
) -> tuple[str, str]:
    entity_id = require_id(entity, kind=kind, context="RDF transformation")
    work_uri = uri(kind, entity_id)
    expression = expression_uri(kind, entity_id)
    work_class = "eli:ComplexWork" if complex_work else "eli:Work"

    triples.append(f"<{expression}> a eli:Expression, vmm:{rdf_type} .")
    triples.append(f"<{expression}> mu:uuid {sparql_string(resource_uuid(expression))} .")
    code = text_value(entity.get("code"))
    title = f"{label} [{code}]" if code else label
    for predicate, value in (
        ("eli:title", title),
        ("schema:code", code),
        ("eli:description", first_value(entity, "korte_omschrijving", "korteOmschrijving")),
        ("epvoc:expressionContent", first_value(entity, "lange_omschrijving", "langeOmschrijving")),
        ("schema:comment", entity.get("commentaar")),
        ("schema:review", entity.get("evaluatie")),
    ):
        if text_value(value) is not None:
            triples.append(f"<{expression}> {predicate} {sparql_string(value)} .")
    priority = sparql_boolean(entity.get("prioritair"))
    if priority is not None:
        triples.append(f'<{expression}> vmm:prioritair "{priority}"^^xsd:boolean .')

    triples.append(f"<{work_uri}> a {work_class} .")
    triples.append(f"<{work_uri}> mu:uuid {sparql_string(resource_uuid(work_uri))} .")
    triples.append(f"<{work_uri}> dct:identifier {sparql_string(entity_id)} .")
    triples.append(f"<{work_uri}> eli:work_type vmm:{rdf_type} .")
    triples.append(f"<{work_uri}> eli:is_realized_by <{expression}> .")
    return work_uri, expression


def add_action(triples: list[str], action: dict[str, Any]) -> str:
    work_uri, _ = add_work(
        triples,
        action,
        kind="actie",
        label="actie",
        rdf_type="Actie",
        complex_work=False,
    )
    return work_uri


def add_actionplan(triples: list[str], actionplan: dict[str, Any]) -> str:
    work_uri, _ = add_work(
        triples,
        actionplan,
        kind="actieplan",
        label="actieplan",
        rdf_type="Actieplan",
        complex_work=True,
    )
    for action in actionplan.get("acties", []) or []:
        action_uri = add_action(triples, action)
        triples.append(f"<{work_uri}> eli:has_member <{action_uri}> .")
    return work_uri


def add_policy(triples: list[str], policy: dict[str, Any]) -> str:
    work_uri, _ = add_work(
        triples,
        policy,
        kind="beleidsdoelstelling",
        label="beleidsdoelstelling",
        rdf_type="Beleidsdoelstelling",
        complex_work=True,
    )
    for actionplan in policy.get("actieplannen", []) or []:
        actionplan_uri = add_actionplan(triples, actionplan)
        triples.append(f"<{work_uri}> eli:has_member <{actionplan_uri}> .")
    return work_uri


def delivery_to_triples(delivery: dict[str, Any]) -> list[str]:
    print(delivery)
    triples: list[str] = []
    delivery_id = require_id(delivery, kind="aanlevering", context="RDF transformation")
    delivery_uri = uri("aanlevering", delivery_id)
    triples.extend(
        [
            f"<{delivery_uri}> a vmm:Aanlevering .",
            f"<{delivery_uri}> mu:uuid {sparql_string(resource_uuid(delivery_uri))} .",
            f"<{delivery_uri}> dct:identifier {sparql_string(delivery_id)} .",
        ]
    )
    report_year = text_value(delivery.get("rapportjaar"))
    if report_year is not None:
        triples.append(f"<{delivery_uri}> schema:datePublished {sparql_string(report_year)} .")

    for strategic in delivery.get("strategische_doelstellingen", []) or []:
        strategic_id = text_value(strategic.get("id"))
        if strategic_id == "0":
            for policy in strategic.get("beleidsdoelstellingen", []) or []:
                policy_uri = add_policy(triples, policy)
                triples.append(f"<{delivery_uri}> dct:hasPart <{policy_uri}> .")
            continue
        strategic_uri, _ = add_work(
            triples,
            strategic,
            kind="strategische_doelstelling",
            label="strategische doelstelling",
            rdf_type="StrategischeDoelstelling",
            complex_work=True,
        )
        triples.append(f"<{delivery_uri}> dct:hasPart <{strategic_uri}> .")
        for policy in strategic.get("beleidsdoelstellingen", []) or []:
            policy_uri = add_policy(triples, policy)
            triples.append(f"<{strategic_uri}> eli:has_member <{policy_uri}> .")

    for actionplan in delivery.get("actieplannen", []) or []:
        actionplan_uri = add_actionplan(triples, actionplan)
        triples.append(f"<{delivery_uri}> dct:hasPart <{actionplan_uri}> .")

    for action in delivery.get("acties", []) or []:
        action_uri = add_action(triples, action)
        triples.append(f"<{delivery_uri}> dct:hasPart <{action_uri}> .")

    return triples


def build_insert_query(triples: list[str]) -> str:
    body = "\n    ".join(triples)
    return f"""{PREFIXES}

INSERT DATA {{
  GRAPH <{PUBLIC_GRAPH}> {{
    {body}
  }}
}}""".strip()

## 5. Generate and insert batches

Virtuoso receives bounded `INSERT DATA` batches. In dry-run mode the notebook validates and
counts every batch without contacting the endpoint.

In [11]:
generated_updates: list[tuple[int, str, list[str]]] = []
for line_number, delivery in deliveries:
    delivery_id = require_id(delivery, kind="aanlevering", context=f"Line {line_number}")
    triples = delivery_to_triples(delivery)
    generated_updates.append((line_number, delivery_id, triples))

print(f"Generated {len(generated_updates)} delivery updates.")
print(f"Generated {sum(len(triples) for _, _, triples in generated_updates)} RDF triples.")

successful = 0
failed: list[tuple[int, str, str]] = []

for index, (line_number, delivery_id, triples) in enumerate(generated_updates, start=1):
    batches = [
        triples[offset : offset + MAX_TRIPLES_PER_UPDATE]
        for offset in range(0, len(triples), MAX_TRIPLES_PER_UPDATE)
    ]
    try:
        if DRY_RUN:
            print(f"[DRY RUN] {index}/{len(generated_updates)} delivery {delivery_id}: {len(batches)} batch(es)")
            continue
        for batch in batches:
            sparql_update(build_insert_query(batch))
        successful += 1
        print(f"Inserted {index}/{len(generated_updates)}: delivery {delivery_id} ({len(batches)} batch(es))")
    except Exception as exc:
        error = f"{type(exc).__name__}: {exc}"
        failed.append((line_number, delivery_id, error))
        print(f"FAILED line {line_number}, delivery {delivery_id}: {error}")

if DRY_RUN:
    print("Dry run complete; no SPARQL updates were sent.")
elif failed:
    details = "; ".join(f"line {line}, delivery {delivery}: {error}" for line, delivery, error in failed)
    raise RuntimeError(f"{len(failed)} deliveries failed to insert: {details}")
else:
    print(f"Inserted all {successful} deliveries successfully.")

{'id': 10000158105, 'bestuur_id': 61, 'type_rapport': 'Meerjarenplan', 'rapportjaar': 2026, 'kwartaal': None, 'kredietjaar': 2026, 'eindjaar': 2031, 'meest_recente': 'Ja', 'status_rapport': 'Origineel-Beginkrediet-2026', 'toezicht_status': 'Onbepaald', 'presentatie_niveau': 'Actieplan', 'oormerk': 'Beginkrediet', 'volgnummer': 1, 'afgevlagd': 'Nee', 'datum_verwerking': '2025-04-02 10:42', 'datum_vaststelling': None, 'datum_goedkeuring': None, 'strategische_doelstellingen': [{'id': 2315855, 'code': 'Hove', 'korte_omschrijving': 'Want het dorp is een wereld.', 'prioritair': False, 'lange_omschrijving': 'Want het dorp is een wereld.', 'commentaar': None, 'evaluatie': None, 'dummy': '0   ', 'beleidsdoelstellingen': [{'id': 2315856, 'code': 'BD000004', 'korte_omschrijving': 'Het AGB sport en ontspanning ', 'prioritair': False, 'lange_omschrijving': 'Het AGB sport en ontspanning zorgt voor het beheer, de exploitatie, de rendabilisering en de valorisering van infrastructuren bestemd voor spor